# PoolSafe — V4: continuidade temporal da evidência de queda
Compara **V3 de referência** e **V4 experimental** nas mesmas caixas, sem escolher uma classe global pela maior confiança.

A V4 exige dez evidências reais de queda em até onze frames na configuração atual. Tolera uma interrupção e permite uma transferência conservadora de evidência pendente entre IDs. Não transfere episódios ativos nem identifica pessoas. Mantém desequilíbrio por 15 frames, encerramento por 15 normais consecutivos, elevação de gravidade, cooldown e associação de eventos da V3.

**Comece por `replay_zip`:** envie um ZIP V3 recente. Não precisa de `best.pt`, vídeo ou GPU. Depois use `video` para verificar o fluxo com o original e os mesmos pesos. Nenhum modo envia notificações ou treina o modelo.


In [ ]:
MODO_TESTE = 'video'  # 'replay_zip' ou 'video'
assert MODO_TESTE in ('replay_zip', 'video')
if MODO_TESTE == 'video':
    import subprocess, sys
    subprocess.check_call([sys.executable,'-m','pip','install','-q',
                           'ultralytics==8.4.173','opencv-python'])


## 1. Enviar arquivos
No replay, envie um único ZIP com `track_v3` ou `replay_v3`, contendo detecções, configuração e eventos. O notebook verifica se o motor de referência reproduz frame, ID e classe dos eventos originais. Se essa verificação falhar, a comparação é interrompida.

No modo vídeo, envie o `best.pt` de três classes e o vídeo original sem caixas. O detector e o ByteTrack executam **uma única vez**; V3 e V4 recebem exatamente as mesmas detecções. A anotação V4 lê novamente o vídeo, sem outra inferência. CPU é usada quando CUDA não está disponível.


In [ ]:
from pathlib import Path
from google.colab import files
if MODO_TESTE == 'replay_zip':
    print('Envie um ZIP de resultados V3 recente, um vídeo por execução.')
    u=files.upload()
    assert len(u)==1 and next(iter(u)).lower().endswith('.zip')
    ZIP_ENTRADA=str(Path.cwd()/next(iter(u)))
else:
    print('Envie somente o best.pt de três classes.')
    u=files.upload()
    assert len(u)==1 and next(iter(u)).lower().endswith('.pt')
    MODELO=str(Path.cwd()/next(iter(u)))
    print('Envie somente o vídeo original, sem caixas.')
    u=files.upload()
    assert len(u)==1
    VIDEO=str(Path.cwd()/next(iter(u)))


Envie somente o best.pt de três classes.


Saving best.pt to best (3).pt
Envie somente o vídeo original, sem caixas.


Saving Queda02Chuva.mp4 to Queda02Chuva.mp4


## 2. Parâmetros
Em `video`, usam-se os parâmetros abaixo. Em `replay_zip`, confianças, persistência, normalidade, cooldown e associação de eventos vêm do ZIP: isso preserva a comparação pareada. A tolerância V4 continua configurada em `CONTINUIDADE`.

`tolerancia_queda=1` significa dez evidências em no máximo onze frames quando o ZIP exige dez. Ausência, classe diferente e baixa confiança podem ocupar o frame de interrupção; nenhum deles conta como evidência positiva. A confirmação só ocorre em um frame com queda aceita. Evidência antiga sai da janela.

O handoff exige referência ausente, sem episódio ativo, geometria recente (≤0,30 s), IoU ≥0,70 e correspondência única nos dois sentidos. Não transfere se há disputa, se a referência está presente ou se sua última caixa foi normal/desequilíbrio aceito. Uma caixa rejeitada pode atualizar apenas a posição para associação: não é somada como queda nem comprova recuperação. Esses limites são hipóteses de desenvolvimento, ainda não validadas com múltiplas pessoas.


In [ ]:
CONFIANCA_POR_CLASSE = {
    'pessoa_normal': 0.30, 'pessoa_desequilibrio': 0.65, 'pessoa_queda': 0.50,
}
FRAMES_POR_CLASSE = {'pessoa_desequilibrio': 15, 'pessoa_queda': 10}
CLASSES_QUE_GERAM_EVENTO = {'pessoa_desequilibrio', 'pessoa_queda'}
FRAMES_NORMAL_PARA_ENCERRAR = 15
COOLDOWN_S = 3.0
DEDUP_IOU = 0.50
DEDUP_INTERVALO_S = 1.5
IOU = 0.7
IMGSZ = 640
CAMERA_ID = 'validacao_01'
MOSTRAR_DESCARTADAS = True
ANOTAR_VIDEO_V4 = True  # Só no modo vídeo; não executa nova inferência.
CONTINUIDADE = dict(tolerancia_queda=1, handoff=True,
    handoff_iou=0.70, handoff_intervalo_s=0.30)
from datetime import datetime
PASTA = Path('/content') / ('poolsafe_episodios_v4_' + datetime.now().strftime('%Y%m%d_%H%M%S_%f'))
PASTA.mkdir()
print('Resultados:', PASTA)


Resultados: /content/poolsafe_episodios_v4_20261026_115509_061464


## 3. Motores e auditoria
A classe `MotorTemporal` preserva a referência V3. `MotorTemporalContinuo` acrescenta janela de evidências e transferência pendente. O `track_id` do CSV continua sendo o ID original do ByteTrack. Nenhuma caixa é removida entre IDs.

`continuidade.json` registra origem, destino, frames transferidos, IoU e intervalo. Eventos V4 de queda contêm `frames_evidencias`: a lista de frames distintos que sustentaram a emissão. O CSV separa o contador do motor e as evidências na janela. Classes não são somadas, nem um ID avança duas vezes no mesmo frame.

Após confirmação, o estado ativo e a proteção contra repetição continuam sob as regras V3. A janela não encerra episódios; apenas 15 normais consecutivos fazem isso na configuração atual. Expiração técnica de ID ausente continua distinta de recuperação.


In [ ]:
"""Validação offline de três classes. Não publica em RabbitMQ ou Firebase."""
import csv
import hashlib
import json
import math
import platform
import subprocess
import time
from collections import Counter
from pathlib import Path

CLASSES = {'pessoa_normal', 'pessoa_desequilibrio', 'pessoa_queda'}
CLASSES_RISCO = ('pessoa_desequilibrio', 'pessoa_queda')


def sha256(path):
    h = hashlib.sha256()
    with open(path, 'rb') as f:
        for b in iter(lambda: f.read(1024 * 1024), b''):
            h.update(b)
    return h.hexdigest()


class MotorTemporal:
    """Contagem por ID e por classe, independente da leitura de vídeo.

    Contadores exigem frames consecutivos da MESMA classe, acima do limiar.
    Ausência, baixa confiança e mudança de classe quebram a sequência.
    Somente normal aceito por normal_frames consecutivos encerra o episódio.
        Um episódio emite abertura e, opcionalmente, uma elevação para queda.
        permitir_escalada=False reproduz a política anterior.
        A elevação confirmada ignora o cooldown, mas não repete a mesma gravidade.
    O cooldown é por câmera. Se bloquear, tenta emitir nos próximos frames
    somente enquanto a mesma condição continua confirmada.
    """

    def __init__(self, confidencias, frames_por_classe, classes_evento,
                 normal_frames=15, cooldown=3.0, fps=15.0, camera_id='validacao_01',
                 permitir_escalada=True, deduplicar_quedas=False,
                 dedup_iou=0.50, dedup_intervalo_s=1.5):
        assert set(confidencias) == CLASSES, 'Confira os três nomes de classe.'
        assert all(math.isfinite(v) and 0 < v <= 1 for v in confidencias.values())
        assert set(frames_por_classe) == set(CLASSES_RISCO)
        assert all(isinstance(v, int) and not isinstance(v, bool) and v >= 1
                   for v in frames_por_classe.values())
        assert set(classes_evento) <= set(CLASSES_RISCO)
        assert isinstance(normal_frames, int) and normal_frames >= 1
        assert math.isfinite(cooldown) and cooldown >= 0 and fps > 0
        self.confidencias = dict(confidencias)
        self.frames_por_classe = dict(frames_por_classe)
        self.classes_evento = set(classes_evento)
        self.normal_frames, self.cooldown, self.fps = normal_frames, cooldown, fps
        self.camera_id = camera_id
        self.permitir_escalada = permitir_escalada
        assert 0 < dedup_iou <= 1 and dedup_intervalo_s > 0
        self.deduplicar_quedas = deduplicar_quedas
        self.dedup_iou, self.dedup_intervalo_s = dedup_iou, dedup_intervalo_s
        self.states, self.events = {}, []
        self.transitions = []
        self.last_event = float('-inf')

    @staticmethod
    def new_state():
        return dict(counts={c: 0 for c in CLASSES_RISCO}, normal=0, active=False,
                    last=-1, starts={c: None for c in CLASSES_RISCO},
                    confirmed_at={c: None for c in CLASSES_RISCO}, episode=0, severity=None,
                    fall_box=None, fall_s=None, event_ref=None, associated=False)

    @staticmethod
    def clear_risk(st, only=None):
        for c in ([only] if only else CLASSES_RISCO):
            st['counts'][c] = 0
            st['starts'][c] = st['confirmed_at'][c] = None

    @staticmethod
    def box_iou(a, b):
        ix = max(0.0, min(a[2], b[2])-max(a[0], b[0]))
        iy = max(0.0, min(a[3], b[3])-max(a[1], b[1]))
        inter = ix*iy
        area_a = max(0.0, a[2]-a[0])*max(0.0, a[3]-a[1])
        area_b = max(0.0, b[2]-b[0])*max(0.0, b[3]-b[1])
        return inter/max(area_a+area_b-inter, 1e-12)

    def duplicate_fall(self, tid, box, video_s, snapshots):
        """Associação de EVENTO, sem alterar IDs ou transferir contadores.

        Só compara quedas aceitas recentes de episódios já confirmados.
        Candidatos de uma mesma referência contam como uma ocorrência.
        Se houver mais de uma ocorrência possível, não suprime por associação.
        """
        if not self.deduplicar_quedas:
            return None, False
        candidates = {}
        for other_tid, st in snapshots.items():
            if other_tid == tid or not st['active'] or st['severity'] != 'pessoa_queda':
                continue
            if st['fall_box'] is None or st['fall_s'] is None or not st['event_ref']:
                continue
            gap = video_s-st['fall_s']
            if not 0 <= gap <= self.dedup_intervalo_s:
                continue
            overlap = self.box_iou(box, st['fall_box'])
            if overlap < self.dedup_iou:
                continue
            item = dict(track_id=other_tid, referencia=st['event_ref'], iou=overlap,
                        intervalo_s=gap)
            root = st['event_ref']
            if root not in candidates or overlap > candidates[root]['iou']:
                candidates[root] = item
        return (next(iter(candidates.values())), False) if len(candidates)==1 else (None, len(candidates)>1)

    def step(self, index, video_s, detections, track=True):
        """Recebe todas as caixas retornadas pelo modo e devolve linhas auditáveis.
        Detecções ausentes do retorno do ByteTrack não podem ser recuperadas aqui.
        """
        rows = []
        for d in detections:
            r = dict(d)
            assert r['classe'] in CLASSES
            r.update(limiar_classe=self.confidencias[r['classe']],
                     aceita=r['confianca'] >= self.confidencias[r['classe']],
                     usada_temporal=False, contador_desequilibrio=0, contador_queda=0,
                     contador_normal=0, episodio_ativo=False, confirmacao_temporal=False,
                     evento_emitido=False, suprimido_cooldown=False,
                     episodio_encerrado=False, gravidade_episodio='',
                     tipo_evento='', episodio=0, evento_referencia='',
                     associado_evento_existente=False, duplicata_associada=False,
                     id_referencia='', iou_associacao='', intervalo_associacao_s='',
                     associacao_ambigua=False, motivo='')
            r['motivo'] = ('sem_motor_no_predict' if r['aceita'] else 'abaixo_limiar')
            rows.append(r)
        if not track:
            return rows

        # Um ID não pode avançar duas vezes no mesmo frame. Prefere caixa aceita;
        # entre caixas aceitas, usa a de maior confiança. As demais ficam no CSV.
        chosen = {}
        for j, r in enumerate(rows):
            tid = r['track_id']
            if tid is None:
                r['motivo'] = 'sem_id' if r['aceita'] else 'abaixo_limiar_sem_id'
                continue
            key = (r['aceita'], r['confianca'])
            if tid not in chosen or key > chosen[tid][0]:
                chosen[tid] = (key, j)
        selected = {j for _, j in chosen.values()}
        for j, r in enumerate(rows):
            if r['track_id'] is not None and j not in selected:
                r['motivo'] = 'duplicata_id_no_frame'

        # Fotografia anterior ao frame: a ordem das caixas não decide associações.
        snapshots = {tid: dict(st) for tid, st in self.states.items()}
        # Atualiza posição da referência com queda aceita deste frame, mas não
        # usa caixa rejeitada como evidência de queda. Sem somar contadores.
        for _, j in chosen.values():
            rr = rows[j]
            ss = snapshots.get(rr['track_id'])
            if ss is not None and rr['aceita'] and rr['classe']=='pessoa_queda':
                ss['fall_box'] = tuple(rr[k] for k in ('x1','y1','x2','y2'))
                ss['fall_s'] = video_s
            elif ss is not None and rr['aceita'] and rr['classe']=='pessoa_normal':
                # Evidência atual de normalidade impede vincular outro ID a uma
                # posição antiga de queda. Não encerra/rearma o episódio aqui.
                ss['fall_box'] = None
        seen = set()
        for _, j in chosen.values():
            r = rows[j]
            tid, cls = r['track_id'], r['classe']
            seen.add(tid)
            st = self.states.setdefault(tid, self.new_state())
            if st['last'] != index - 1:
                self.clear_risk(st)
                st['normal'] = 0
            st['last'] = index
            r['usada_temporal'] = bool(r['aceita'])
            if r['aceita'] and cls == 'pessoa_queda':
                st['fall_box'] = tuple(r[k] for k in ('x1','y1','x2','y2'))
                st['fall_s'] = video_s
            elif r['aceita'] and cls == 'pessoa_normal':
                st['fall_box'] = None

            if not r['aceita']:
                # Rejeitada não é normal e não rearma um episódio ativo.
                self.clear_risk(st)
                st['normal'] = 0
                r['motivo'] = 'abaixo_limiar'
            elif cls == 'pessoa_normal':
                self.clear_risk(st)
                st['normal'] += 1
                r['motivo'] = 'normal_aceito'
                if st['normal'] >= self.normal_frames and st['active']:
                    anterior = st['severity']
                    st['active'] = False
                    st['severity'] = None
                    st['event_ref'] = None
                    st['associated'] = False
                    r['episodio_encerrado'] = True
                    self.transitions.append(dict(frame=index, tempo_video_s=video_s,
                        track_id=tid, episodio=st['episode'],
                        transicao='encerramento_recuperacao', gravidade_anterior=anterior,
                        gravidade_nova=None, contador_normal=st['normal']))
            else:
                st['normal'] = 0
                for other in CLASSES_RISCO:
                    if other != cls:
                        self.clear_risk(st, only=other)
                if st['counts'][cls] == 0:
                    st['starts'][cls] = video_s
                st['counts'][cls] += 1
                r['motivo'] = 'aguardando_persistencia'
                if st['counts'][cls] >= self.frames_por_classe[cls]:
                    r['confirmacao_temporal'] = True
                    if st['confirmed_at'][cls] is None:
                        st['confirmed_at'][cls] = video_s
                    # Uma escalada pertence ao MESMO episódio e exige a sua
                    # própria sequência de queda; não soma classes.
                    escalada = (self.permitir_escalada and st['active']
                        and st['severity'] == 'pessoa_desequilibrio'
                        and cls == 'pessoa_queda')
                    duplicate, ambiguous = (None, False)
                    if cls == 'pessoa_queda' and (not st['active'] or escalada):
                        duplicate, ambiguous = self.duplicate_fall(
                            tid, st['fall_box'], video_s, snapshots)
                    r['associacao_ambigua'] = ambiguous
                    if cls not in self.classes_evento:
                        r['motivo'] = 'classe_sem_evento'
                    elif st['active'] and not escalada:
                        r['motivo'] = 'episodio_ja_ativo'
                    elif duplicate is not None:
                        # Confirmação pertence a uma queda já notificada por outro ID.
                        # Marca o novo ID como associado, sem criar evento e sem
                        # reiniciar cooldown. Se persistir, continua sem repetir.
                        if not st['active']:
                            st['episode'] += 1
                        st['active'] = True
                        st['severity'] = 'pessoa_queda'
                        st['event_ref'] = duplicate['referencia']
                        st['associated'] = True
                        r.update(duplicata_associada=True,
                            id_referencia=duplicate['track_id'],
                            iou_associacao=duplicate['iou'],
                            intervalo_associacao_s=duplicate['intervalo_s'],
                            motivo='queda_associada_evento_existente')
                        self.transitions.append(dict(frame=index, tempo_video_s=video_s,
                            track_id=tid, episodio=st['episode'],
                            transicao='associacao_duplicata_queda',
                            evento_referencia=st['event_ref'],
                            id_referencia=duplicate['track_id'],
                            iou=duplicate['iou'], intervalo_s=duplicate['intervalo_s']))
                    elif not escalada and video_s - self.last_event < self.cooldown:
                        r['suprimido_cooldown'] = True
                        r['motivo'] = 'cooldown_aguardar_persistencia'
                        # Não marca ativo: evita perder definitivamente um evento
                        # apenas porque sua primeira confirmação caiu no cooldown.
                    else:
                        anterior = st['severity']
                        if not st['active']:
                            st['episode'] += 1
                        st['active'] = True
                        st['severity'] = cls
                        if not st['event_ref']:
                            st['event_ref'] = f'{self.camera_id}:{tid}:{st["episode"]}'
                        st['associated'] = False
                        tipo = 'elevacao_gravidade' if escalada else 'abertura_episodio'
                        r['tipo_evento'] = tipo
                        self.transitions.append(dict(frame=index, tempo_video_s=video_s,
                            track_id=tid, episodio=st['episode'], transicao=tipo,
                            gravidade_anterior=anterior, gravidade_nova=cls))
                        self.last_event = video_s
                        r['evento_emitido'] = True
                        r['motivo'] = 'evento_local_emitido'
                        self.events.append(dict(camera_id=self.camera_id, track_id=tid,
                            episodio=st['episode'], frame=index, tempo_video_s=round(video_s, 6),
                            tipo_evento=tipo, gravidade_anterior=anterior,
                            evento_referencia=st['event_ref'],
                            cooldown_ignorado_por_escalada=bool(escalada),
                            classe_origem=cls, confidence=r['confianca'],
                            limiar_classe=self.confidencias[cls],
                            frames_exigidos=self.frames_por_classe[cls],
                            inicio_sequencia_s=st['starts'][cls],
                            primeira_confirmacao_s=st['confirmed_at'][cls],
                            espera_cooldown_s=max(0.0, video_s-st['confirmed_at'][cls]),
                            type='confirmacao_local'))
            r.update(contador_desequilibrio=st['counts']['pessoa_desequilibrio'],
                     contador_queda=st['counts']['pessoa_queda'],
                     contador_normal=st['normal'], episodio_ativo=st['active'],
                     gravidade_episodio=st['severity'] or '', episodio=st['episode'],
                     evento_referencia=st['event_ref'] or '',
                     associado_evento_existente=st['associated'])
        for tid, st in list(self.states.items()):
            if tid not in seen:
                self.clear_risk(st)
                st['normal'] = 0
                # Ausência não confirma recuperação. Um ID perdido por muito
                # tempo é descartado; reaparecimento pode produzir outro evento.
                if index - st['last'] > self.fps * 30:
                    self.transitions.append(dict(frame=index, tempo_video_s=video_s,
                        track_id=tid, episodio=st['episode'], transicao='expiracao_id_ausente',
                        gravidade_anterior=st['severity'], gravidade_nova=None,
                        observacao='Expiração técnica após 30 s; não comprova recuperação.'))
                    del self.states[tid]
        return rows


def run(model_path, video_path, output_dir, mode='predict', confidencias=None,
        frames_por_classe=None, classes_evento=None, iou=0.7, imgsz=640,
        normal_frames=15, cooldown=3.0, camera_id='validacao_01',
        device=None, mostrar_descartadas=True, permitir_escalada=True,
        deduplicar_quedas=False, dedup_iou=0.50, dedup_intervalo_s=1.5):
    """Detector, tracker e motor novos em cada chamada. Não treina.

    O limite geral é o menor limite por classe. ByteTrack associa as caixas
    antes do filtro temporal; seus próprios limiares também influenciam IDs.
    O CSV registra o que cada modo retornou, não propostas internas descartadas
    por NMS, pelo limite geral ou pelo próprio tracker.
    """
    import cv2
    import torch
    import ultralytics
    from ultralytics import YOLO

    assert mode in ('predict', 'track')
    assert math.isfinite(iou) and 0 < iou <= 1 and imgsz >= 32
    confidencias = dict(confidencias or {
        'pessoa_normal': 0.30, 'pessoa_desequilibrio': 0.65, 'pessoa_queda': 0.50})
    frames_por_classe = dict(frames_por_classe or {
        'pessoa_desequilibrio': 15, 'pessoa_queda': 15})
    classes_evento = set(CLASSES_RISCO if classes_evento is None else classes_evento)
    # Valida os parâmetros antes de abrir vídeo/criar pasta.
    motor = MotorTemporal(confidencias, frames_por_classe, classes_evento,
                          normal_frames, cooldown, 15.0, camera_id, permitir_escalada,
                          deduplicar_quedas, dedup_iou, dedup_intervalo_s)
    conf_geral = min(confidencias.values())
    model_path, video_path = Path(model_path), Path(video_path)
    assert model_path.is_file() and video_path.is_file(), 'Modelo/vídeo inexistente'
    detector = YOLO(str(model_path))
    source_names = detector.names
    if isinstance(source_names, (list, tuple)):
        source_names = dict(enumerate(source_names))
    names = {int(k): str(v) for k, v in source_names.items()}
    assert len(names) == 3 and set(names.values()) == CLASSES, (
        f'Use o novo best.pt de três classes. Classes encontradas: {names}')
    device = (0 if torch.cuda.is_available() else 'cpu') if device is None else device
    cap = cv2.VideoCapture(str(video_path))
    writer = None
    out = Path(output_dir)
    try:
        assert cap.isOpened(), 'Falha ao abrir vídeo'
        fps = float(cap.get(cv2.CAP_PROP_FPS))
        width, height = int(cap.get(3)), int(cap.get(4))
        assert math.isfinite(fps) and fps > 0 and width > 0 and height > 0
        motor.fps = fps
        out.mkdir(parents=True, exist_ok=False)
        raw = out / 'resultado_mp4v.mp4'
        writer = cv2.VideoWriter(str(raw), cv2.VideoWriter_fourcc(*'mp4v'), fps, (width, height))
        assert writer.isOpened(), 'Falha no VideoWriter'
        config = dict(mode=mode, model=str(model_path), model_sha256=sha256(model_path),
            video=str(video_path), video_sha256=sha256(video_path), names=names,
            confianca_por_classe=confidencias, conf_geral=conf_geral,
            frames_por_classe=frames_por_classe, classes_que_geram_evento=sorted(classes_evento),
            iou=iou, imgsz=imgsz, normal_frames=normal_frames, cooldown=cooldown,
            camera_id=camera_id, device=device, fps=fps,
            duracao_persistencia_nominal_s={c: (n-1)/fps for c,n in frames_por_classe.items()},
            ultralytics=ultralytics.__version__, torch=torch.__version__,
            python=platform.python_version(), tracker='bytetrack.yaml' if mode=='track' else None,
            filtro='por classe após retorno do detector/tracker; antes dos contadores',
            politica=('abertura e elevação para queda por episódio' if permitir_escalada
                      else 'anterior: um evento por episódio de ID'),
            versao_motor='episodios_v3_20261025', permitir_escalada=permitir_escalada,
            deduplicar_quedas=deduplicar_quedas, dedup_iou=dedup_iou,
            dedup_intervalo_s=dedup_intervalo_s,
            dedup_policy='associação espacial-temporal de eventos; não é reidentificação',
            recuperacao='15 normais consecutivos por padrão; ausência não rearma',
            cooldown_policy='câmera: aberturas aguardam; elevação confirmada ignora; reavalia persistência',
            time_basis='(frame-1)/FPS nominal; não latência RTSP/app',
            mostrar_descartadas=mostrar_descartadas)
        (out/'configuracao.json').write_text(json.dumps(config, indent=2, ensure_ascii=False))
        # Preserva a configuração efetiva do ByteTrack usada pela biblioteca.
        if mode == 'track':
            from ultralytics.utils.checks import check_yaml
            tracker_file = Path(check_yaml('bytetrack.yaml'))
            (out/'bytetrack_usado.yaml').write_text(tracker_file.read_text())
        index, inference_s = 0, 0.0
        recebidas, aceitas, descartadas = Counter(), Counter(), Counter()
        sem_id = frames_vazios = frames_sem_aceitas = cooldown_frames = 0
        started = time.perf_counter()
        status = 'iniciado'
        csvfields = ['frame','tempo_video_s','track_id','classe','confianca','limiar_classe',
            'aceita','usada_temporal','motivo','x1','y1','x2','y2',
            'contador_desequilibrio','contador_queda','contador_normal','episodio_ativo',
            'confirmacao_temporal','evento_emitido','suprimido_cooldown','episodio_encerrado',
            'gravidade_episodio','tipo_evento','episodio','evento_referencia',
            'associado_evento_existente','duplicata_associada','id_referencia',
            'iou_associacao','intervalo_associacao_s','associacao_ambigua','inferencia_ms']
        try:
            with open(out/'deteccoes.csv', 'w', newline='', encoding='utf-8') as f:
                csvout = csv.DictWriter(f, fieldnames=csvfields)
                csvout.writeheader()
                while True:
                    ok, image = cap.read()
                    if not ok:
                        break
                    index += 1
                    video_s = (index-1)/fps
                    use_cuda = str(device).lower() != 'cpu' and torch.cuda.is_available()
                    if use_cuda:
                        torch.cuda.synchronize()
                    t0 = time.perf_counter()
                    kwargs = dict(conf=conf_geral, iou=iou, imgsz=imgsz, device=device, verbose=False)
                    result = (detector.predict(image, **kwargs) if mode == 'predict' else
                        detector.track(image, persist=True, tracker='bytetrack.yaml', **kwargs))[0]
                    if use_cuda:
                        torch.cuda.synchronize()
                    elapsed = time.perf_counter()-t0
                    inference_s += elapsed
                    detections = []
                    if result.boxes is not None:
                        for box in result.boxes:
                            cls = int(box.cls.item())
                            score = float(box.conf.item())
                            coords = box.xyxy[0].cpu().tolist()
                            tid = int(box.id.item()) if box.id is not None else None
                            detections.append(dict(track_id=tid, classe=names[cls], confianca=score,
                                x1=coords[0], y1=coords[1], x2=coords[2], y2=coords[3]))
                    rows = motor.step(index, video_s, detections, track=(mode=='track'))
                    if not rows:
                        frames_vazios += 1
                    if not any(r['aceita'] for r in rows):
                        frames_sem_aceitas += 1
                    if any(r['suprimido_cooldown'] for r in rows):
                        cooldown_frames += 1
                    for row in rows:
                        cls = row['classe']
                        recebidas[cls] += 1
                        (aceitas if row['aceita'] else descartadas)[cls] += 1
                        if mode == 'track' and row['track_id'] is None:
                            sem_id += 1
                        if row['aceita'] or mostrar_descartadas:
                            color = {'pessoa_normal': (0,180,0), 'pessoa_desequilibrio': (0,165,255),
                                     'pessoa_queda': (0,0,255)}[cls] if row['aceita'] else (150,150,150)
                            label = f"{cls} {row['confianca']:.2f}/{row['limiar_classe']:.2f}"
                            if not row['aceita']:
                                label += ' DESCARTADA'
                            elif mode == 'track':
                                count = row['contador_desequilibrio'] if cls == 'pessoa_desequilibrio' else row['contador_queda']
                                label += f" ID={row['track_id']}"
                                if cls in CLASSES_RISCO:
                                    label += f" {count}/{frames_por_classe[cls]}"
                                if row['associado_evento_existente']:
                                    label += ' ASSOCIADO'
                                if row['episodio_ativo']:
                                    label += ' EPISODIO ATIVO'
                                if row['evento_emitido']:
                                    label += ' ' + row['tipo_evento'].upper()
                                if row['suprimido_cooldown']:
                                    label += ' COOLDOWN'
                            x1,y1,x2,y2 = (int(row[k]) for k in ['x1','y1','x2','y2'])
                            cv2.rectangle(image, (x1,y1), (x2,y2), color, 2)
                            cv2.putText(image, label, (max(0,x1),max(20,y1-8)),
                                        cv2.FONT_HERSHEY_SIMPLEX, 0.45, color, 1)
                        row.update(frame=index, tempo_video_s=video_s, inferencia_ms=elapsed*1000)
                    if not rows:
                        rows = [dict(frame=index, tempo_video_s=video_s, classe='sem_deteccao',
                                     motivo='nenhuma_caixa_retornada', inferencia_ms=elapsed*1000)]
                    csvout.writerows(rows)
                    # O cabeçalho distingue contadores, não a ocorrência real de queda.
                    cv2.putText(image, f"{mode} frame={index} t={video_s:.2f}s eventos={len(motor.events)}",
                                (10,20), cv2.FONT_HERSHEY_SIMPLEX, 0.5, (255,255,255), 1)
                    writer.write(image)
            status = 'concluido'
        finally:
            wall = time.perf_counter()-started
            (out/'transicoes.json').write_text(json.dumps(motor.transitions, indent=2, ensure_ascii=False))
            (out/'eventos.json').write_text(json.dumps(motor.events, indent=2, ensure_ascii=False))
            summary = dict(status=status, frames=index, duracao_nominal_s=index/fps,
                eventos_locais=len(motor.events),
                aberturas=sum(e['tipo_evento']=='abertura_episodio' for e in motor.events),
                elevacoes=sum(e['tipo_evento']=='elevacao_gravidade' for e in motor.events),
                encerramentos=sum(t['transicao']=='encerramento_recuperacao' for t in motor.transitions),
                associacoes_duplicata=sum(t['transicao']=='associacao_duplicata_queda' for t in motor.transitions),
                eventos_por_classe={c: sum(e['classe_origem']==c for e in motor.events) for c in CLASSES_RISCO},
                deteccoes_recebidas={c:recebidas[c] for c in sorted(CLASSES)},
                deteccoes_aceitas={c:aceitas[c] for c in sorted(CLASSES)},
                deteccoes_descartadas={c:descartadas[c] for c in sorted(CLASSES)},
                deteccoes_sem_id=sem_id, frames_sem_caixas_retornadas=frames_vazios,
                frames_sem_deteccao_aceita=frames_sem_aceitas,
                frames_com_supressao_cooldown=cooldown_frames,
                processamento_s=wall, inferencia_media_ms=inference_s/max(index,1)*1000,
                fps_processamento=index/max(wall,1e-9),
                observacao='Sem referência humana: não calcula precisão, revocação ou falsos alertas. Eventos são locais.')
            (out/'resumo.json').write_text(json.dumps(summary, indent=2, ensure_ascii=False))
    finally:
        cap.release()
        if writer is not None:
            writer.release()
    assert index > 0, 'Nenhum frame foi decodificado; confira o vídeo.'
    web = out/'resultado_h264.mp4'
    try:
        subprocess.run(['ffmpeg','-y','-i',str(raw),'-c:v','libx264','-preset','veryfast',
            '-pix_fmt','yuv420p','-movflags','+faststart',str(web)], check=True, capture_output=True)
    except (FileNotFoundError, subprocess.CalledProcessError):
        print('Conversão H.264 falhou; MP4 original preservado:', raw)
        web = raw
    print(json.dumps(summary, indent=2, ensure_ascii=False))
    return str(web)

"""Continuidade limitada da evidência de queda; motor V3 preservado como base."""
from collections import deque


class MotorTemporalContinuo(MotorTemporal):
    """V4 experimental: N evidências reais de queda em até N+T frames.

    Normalidade e desequilíbrio continuam estritamente consecutivos.
    Ausência não conta como normal nem como queda. Não remove caixas.
    Um handoff transfere somente evidência pendente, nunca encerra episódios.
    """

    def __init__(self, *args, tolerancia_queda=1, handoff=True,
                 handoff_iou=0.70, handoff_intervalo_s=0.30, **kwargs):
        super().__init__(*args, **kwargs)
        assert isinstance(tolerancia_queda, int) and 0 <= tolerancia_queda <= 2
        assert 0 < handoff_iou <= 1 and handoff_intervalo_s > 0
        self.tolerancia_queda = tolerancia_queda
        self.handoff = handoff
        self.handoff_iou = handoff_iou
        self.handoff_intervalo_s = handoff_intervalo_s
        self.evidencias_queda = {}
        self.ultima_caixa = {}
        self.ultima_presenca = {}
        self.ultima_classe_aceita = {}
        self.auditoria_continuidade = []
        self._indice_anterior = 0

    def step(self, index, video_s, detections, track=True):
        if not track:
            return super().step(index, video_s, detections, track=False)
        assert index > self._indice_anterior, 'Frames precisam avançar; não processe um frame duas vezes.'
        self._indice_anterior = index
        # Mesma escolha por ID do V3; nenhuma supressão entre classes/IDs.
        chosen = {}
        for d in detections:
            tid = d['track_id']
            if tid is None:
                continue
            key = (d['confianca'] >= self.confidencias[d['classe']], d['confianca'])
            if tid not in chosen or key > chosen[tid][0]:
                chosen[tid] = (key, d)
        atuais = {tid: pair[1] for tid, pair in chosen.items()}
        janela = self.frames_por_classe['pessoa_queda'] + self.tolerancia_queda
        for tid, hist in list(self.evidencias_queda.items()):
            while hist and hist[0][0] < index-janela+1:
                hist.popleft()
            if not hist:
                del self.evidencias_queda[tid]

        # Handoff somente quando a referência está ausente e sem episódio ativo.
        # A correspondência precisa ser única nos dois sentidos. Duas pessoas
        # atuais disputando a mesma referência impedem a transferência.
        pares = {}
        disputas = Counter()
        if self.handoff:
            # Inclui caixas normais/desequilíbrio na verificação de disputa.
            for old, hist in self.evidencias_queda.items():
                if old in atuais or not hist or self.states.get(old, {}).get('active', False):
                    continue
                gap = video_s-self.ultima_presenca.get(old, float('-inf'))
                if not 0 <= gap <= self.handoff_intervalo_s:
                    continue
                for tid, d in atuais.items():
                    if d['confianca'] < self.confidencias[d['classe']]:
                        continue
                    box = tuple(d[k] for k in ('x1','y1','x2','y2'))
                    if self.box_iou(box, self.ultima_caixa[old]) >= self.handoff_iou:
                        disputas[old] += 1
            for tid, d in atuais.items():
                if d['classe'] != 'pessoa_queda' or d['confianca'] < self.confidencias['pessoa_queda']:
                    continue
                if self.states.get(tid, {}).get('active', False):
                    continue
                box = tuple(d[k] for k in ('x1','y1','x2','y2'))
                for old, hist in self.evidencias_queda.items():
                    if old == tid or old in atuais or not hist:
                        continue
                    if self.states.get(old, {}).get('active', False):
                        continue
                    # Uma caixa rejeitada mantém apenas a geometria; não é
                    # prova de recuperação nem evidência positiva de queda.
                    if self.ultima_classe_aceita.get(old) in ('pessoa_normal', 'pessoa_desequilibrio'):
                        continue
                    gap = video_s-self.ultima_presenca.get(old, float('-inf'))
                    if not 0 <= gap <= self.handoff_intervalo_s:
                        continue
                    overlap = self.box_iou(box, self.ultima_caixa[old])
                    if overlap >= self.handoff_iou:
                        pares.setdefault(tid, []).append((old, overlap, gap))
            usados = Counter(old for opts in pares.values() for old, _, _ in opts)
            # Fotografia anterior: não encadeia transferências no mesmo frame.
            transferencias = [(tid, opts[0]) for tid, opts in pares.items()
                              if len(opts) == 1 and usados[opts[0][0]] == 1
                              and disputas[opts[0][0]] == 1]
            for tid, (old, overlap, gap) in transferencias:
                origem = list(self.evidencias_queda.get(old, []))
                destino = list(self.evidencias_queda.get(tid, []))
                unidos = {f: (f, t) for f, t in origem+destino}
                self.evidencias_queda[tid] = deque(unidos[f] for f in sorted(unidos))
                self.evidencias_queda.pop(old, None)
                self.auditoria_continuidade.append(dict(frame=index, tempo_video_s=video_s,
                    transicao='handoff_evidencia_pendente', id_origem=old, track_id=tid,
                    iou=overlap, intervalo_s=gap, evidencias_transferidas=len(origem),
                    frames_origem=[f for f, _ in origem],
                    frames_destino_anteriores=[f for f, _ in destino],
                    referencia_geometrica_aceita=self.ultima_classe_aceita.get(old) is not None))

        for tid, d in atuais.items():
            self.ultima_caixa[tid] = tuple(d[k] for k in ('x1','y1','x2','y2'))
            self.ultima_presenca[tid] = video_s
            self.ultima_classe_aceita[tid] = (d['classe'] if d['confianca'] >= self.confidencias[d['classe']] else None)
            if d['classe'] == 'pessoa_queda' and d['confianca'] >= self.confidencias['pessoa_queda']:
                hist = self.evidencias_queda.setdefault(tid, deque())
                hist.append((index, video_s))
                st = self.states.setdefault(tid, self.new_state())
                # O super.step acrescentará somente a evidência atual. As
                # interrupções toleradas nunca viram evidências positivas.
                st['counts']['pessoa_queda'] = len(hist)-1
                st['starts']['pessoa_queda'] = hist[0][1]
                if len(hist) < self.frames_por_classe['pessoa_queda']:
                    st['confirmed_at']['pessoa_queda'] = None
                st['last'] = index-1
        rows = super().step(index, video_s, detections, track=True)
        for r in rows:
            tid = r['track_id']
            hist = self.evidencias_queda.get(tid, [])
            r['evidencias_queda_janela'] = len(hist)
            r['janela_queda_frames'] = janela
            r['interrupcoes_queda_janela'] = ((index-hist[0][0]+1)-len(hist)) if hist else 0
            if r.get('evento_emitido') and r['classe'] == 'pessoa_queda':
                evento = next(e for e in reversed(self.events) if e['frame'] == index and e['track_id'] == tid)
                evento.update(criterio_temporal='evidencias_reais_em_janela_limitada',
                    janela_max_frames=janela, evidencias_queda=len(hist),
                    tolerancia_frames=self.tolerancia_queda,
                    frames_evidencias=[f for f, _ in hist])
            if r.get('episodio_encerrado'):
                self.evidencias_queda.pop(tid, None)
        # Limita metadados de IDs ausentes; isso não declara recuperação.
        for tid in list(self.ultima_presenca):
            if video_s-self.ultima_presenca[tid] > 30 and tid not in self.states:
                self.ultima_presenca.pop(tid, None)
                self.ultima_caixa.pop(tid, None)
                self.ultima_classe_aceita.pop(tid, None)
                self.evidencias_queda.pop(tid, None)
        return rows


"""Entrada/saída para comparação pareada V3/V4 usando exatamente as mesmas caixas."""
import io
import zipfile

CONTINUIDADE_PADRAO = dict(tolerancia_queda=1, handoff=True,
    handoff_iou=0.70, handoff_intervalo_s=0.30)


def carregar_registros(cfg, csv_text):
    assert cfg.get('permitir_escalada') is True
    assert cfg.get('deduplicar_quedas') is True, 'Use resultados do motor V3 com associação de quedas.'
    fps = float(cfg['fps'])
    assert math.isfinite(fps) and fps > 0
    frames = {}
    for r in csv.DictReader(io.StringIO(csv_text)):
        f = int(r['frame']); ds = frames.setdefault(f, [])
        if r['classe'] == 'sem_deteccao':
            continue
        assert r['classe'] in CLASSES
        score = float(r['confianca'])
        box = {k: float(r[k]) for k in ('x1','y1','x2','y2')}
        assert math.isfinite(score) and 0 <= score <= 1
        assert all(math.isfinite(v) for v in box.values())
        assert box['x2'] > box['x1'] and box['y2'] > box['y1']
        ds.append(dict(track_id=int(float(r['track_id'])) if r['track_id'] else None,
            classe=r['classe'], confianca=score, **box))
    assert frames and min(frames)==1
    assert sorted(frames)==list(range(1,max(frames)+1)), 'CSV precisa conter todos os frames, incluindo vazios.'
    return frames


def carregar_zip_v3(path):
    with zipfile.ZipFile(path) as z:
        for folder in ('track_v3', 'replay_v3'):
            candidates = [p for p in z.namelist() if p.endswith(folder+'/configuracao.json')]
            if candidates:
                assert len(candidates)==1, 'ZIP com mais de uma referência; use um vídeo por execução.'
                prefix = candidates[0][:-len('configuracao.json')]
                break
        else:
            raise AssertionError('Envie um ZIP V3 com track_v3 ou replay_v3. ZIP V2 não é referência desta comparação.')
        cfg = json.loads(z.read(prefix+'configuracao.json'))
        ref = json.loads(z.read(prefix+'eventos.json'))
        csv_bytes = z.read(prefix+'deteccoes.csv')
    frames = carregar_registros(cfg, csv_bytes.decode('utf-8-sig'))
    origem = dict(sha256_zip_entrada=sha256(path), pasta_origem=prefix,
                  sha256_csv_entrada=hashlib.sha256(csv_bytes).hexdigest())
    return cfg, ref, frames, origem


def assinatura(eventos):
    return [(e['frame'],e['track_id'],e['classe_origem']) for e in eventos]


def executar_motor(cfg, frames, destino, v4=False, origem=None, continuidade=None):
    cls = MotorTemporalContinuo if v4 else MotorTemporal
    opts = dict(CONTINUIDADE_PADRAO if continuidade is None else continuidade) if v4 else {}
    m = cls(cfg['confianca_por_classe'], cfg['frames_por_classe'],
        set(cfg['classes_que_geram_evento']), normal_frames=cfg['normal_frames'],
        cooldown=cfg['cooldown'], fps=cfg['fps'], camera_id=cfg['camera_id'],
        permitir_escalada=True, deduplicar_quedas=True,
        dedup_iou=cfg.get('dedup_iou',.5),
        dedup_intervalo_s=cfg.get('dedup_intervalo_s',1.5), **opts)
    rows = []
    for f in sorted(frames):
        rr = m.step(f,(f-1)/cfg['fps'],frames[f])
        if not rr:
            rr = [dict(classe='sem_deteccao', motivo='nenhuma_caixa_retornada')]
        for r in rr:
            r.update(frame=f,tempo_video_s=(f-1)/cfg['fps'])
        rows.extend(rr)
    out = Path(destino); out.mkdir(parents=True,exist_ok=False)
    keys = list(dict.fromkeys(k for r in rows for k in r))
    with open(out/'deteccoes.csv','w',newline='',encoding='utf-8') as f:
        writer=csv.DictWriter(f,fieldnames=keys);writer.writeheader();writer.writerows(rows)
    config = dict(cfg, mode='replay', versao_motor='episodios_v4_continuidade_20261025' if v4 else 'episodios_v3_20261025',
        inferencia_executada_nesta_etapa=False, origem_registros=origem or {}, continuidade=opts,
        criterio_queda='N evidências reais em no máximo N+T frames; atual precisa ser queda aceita' if v4 else 'N frames consecutivos',
        recuperacao='normalidade aceita por 15 frames consecutivos por padrão; ausência não rearma',
        handoff_policy='somente evidência pendente, sem transferir estado de episódio ativo' if v4 else None)
    summary = dict(frames=max(frames), eventos_locais=len(m.events),
        eventos_por_classe={c:sum(e['classe_origem']==c for e in m.events) for c in CLASSES_RISCO},
        aberturas=sum(e['tipo_evento']=='abertura_episodio' for e in m.events),
        elevacoes=sum(e['tipo_evento']=='elevacao_gravidade' for e in m.events),
        encerramentos=sum(t['transicao']=='encerramento_recuperacao' for t in m.transitions),
        associacoes_duplicata=sum(t['transicao']=='associacao_duplicata_queda' for t in m.transitions),
        transferencias_pendentes=len(getattr(m,'auditoria_continuidade',[])),
        observacao='Replay de caixas fixas. Não mede acurácia, latência do app ou velocidade de inferência.')
    for name, data in [('configuracao.json',config),('resumo.json',summary),('eventos.json',m.events),
                       ('transicoes.json',m.transitions),('continuidade.json',getattr(m,'auditoria_continuidade',[]))]:
        (out/name).write_text(json.dumps(data,indent=2,ensure_ascii=False))
    return m, rows


def comparar_zip_v3(path, pasta, continuidade=None):
    cfg, ref, frames, origem = carregar_zip_v3(path)
    print('Vídeo:',cfg['video'])
    print('Confianças preservadas do ZIP:',cfg['confianca_por_classe'])
    print('Persistência do ZIP:',cfg['frames_por_classe'],'; normal:',cfg['normal_frames'])
    baseline, _ = executar_motor(cfg,frames,Path(pasta)/'replay_v3',origem=origem)
    assert assinatura(baseline.events)==assinatura(ref), 'V3 não reproduziu os eventos de referência. Pare a comparação.'
    (Path(pasta)/'referencia_verificada.json').write_text(json.dumps(dict(reproduz_eventos_v3=True,
        criterio=['frame','track_id','classe_origem'], **origem),indent=2,ensure_ascii=False))
    executar_motor(cfg,frames,Path(pasta)/'replay_v4',v4=True,origem=origem,continuidade=continuidade)
    return ['replay_v3','replay_v4']


def anotar_v4(video, rows, destino, mostrar_descartadas=True):
    """Anota o original com as decisões V4; não executa outra inferência."""
    import cv2
    byframe = {}
    for r in rows:
        byframe.setdefault(r['frame'],[]).append(r)
    cap=cv2.VideoCapture(str(video));writer=None
    out=Path(destino);raw=out/'resultado_mp4v.mp4'
    index=0
    try:
        assert cap.isOpened(), 'Não foi possível abrir o vídeo original para anotar.'
        fps=float(cap.get(cv2.CAP_PROP_FPS));w,h=int(cap.get(3)),int(cap.get(4))
        assert math.isfinite(fps) and fps>0 and w>0 and h>0
        writer=cv2.VideoWriter(str(raw),cv2.VideoWriter_fourcc(*'mp4v'),fps,(w,h))
        assert writer.isOpened()
        events=0
        while True:
            ok,image=cap.read()
            if not ok:break
            index+=1
            assert index in byframe, 'Vídeo e CSV têm quantidades de frames diferentes.'
            for r in byframe[index]:
                if r['classe']=='sem_deteccao':continue
                events+=int(r.get('evento_emitido',False))
                if not r['aceita'] and not mostrar_descartadas:continue
                color=({'pessoa_normal':(0,180,0),'pessoa_desequilibrio':(0,165,255),
                    'pessoa_queda':(0,0,255)}[r['classe']] if r['aceita'] else (150,150,150))
                x1,y1,x2,y2=(int(r[k]) for k in ('x1','y1','x2','y2'))
                label=f"{r['classe']} {r['confianca']:.2f} ID={r['track_id']}"
                if not r['aceita']:label+=' DESCARTADA'
                elif r['classe']=='pessoa_normal':label+=f" normal={r['contador_normal']}"
                elif r['classe']=='pessoa_queda':label+=f" evidencias={r['evidencias_queda_janela']} janela={r['janela_queda_frames']}"
                else:label+=f" consecutivos={r['contador_desequilibrio']}"
                if r.get('episodio_ativo'):label+=' ATIVO'
                if r.get('evento_emitido'):label+=' EVENTO'
                if r.get('episodio_encerrado'):label+=' RECUPERACAO'
                cv2.rectangle(image,(x1,y1),(x2,y2),color,2)
                cv2.putText(image,label,(max(0,x1),max(40,y1-8)),cv2.FONT_HERSHEY_SIMPLEX,.42,color,1)
            cv2.putText(image,f'V4 frame={index} t={(index-1)/fps:.2f}s eventos={events}',
                (10,20),cv2.FONT_HERSHEY_SIMPLEX,.5,(255,255,255),1)
            writer.write(image)
        assert index==max(byframe), 'Vídeo terminou antes do CSV.'
    finally:
        cap.release()
        if writer is not None:writer.release()
    web=out/'resultado_h264.mp4'
    try:
        subprocess.run(['ffmpeg','-y','-i',str(raw),'-c:v','libx264','-preset','veryfast',
            '-pix_fmt','yuv420p','-movflags','+faststart',str(web)],check=True,capture_output=True)
    except (FileNotFoundError,subprocess.CalledProcessError):
        print('Conversão H.264 indisponível; arquivo MP4 original preservado.')
        web=raw
    return str(web)


def mostrar_comparacao(pasta, execucoes):
    results=[]
    for nome in execucoes:
        p=Path(pasta)/nome
        resumo=json.loads((p/'resumo.json').read_text())
        results.append(dict(execucao=nome,**resumo))
        print('\n',nome,json.dumps(resumo,ensure_ascii=False,indent=2))
        print('EVENTOS',json.dumps(json.loads((p/'eventos.json').read_text()),ensure_ascii=False,indent=2))
        if (p/'continuidade.json').exists():
            print('TRANSFERÊNCIAS',json.loads((p/'continuidade.json').read_text()))
    (Path(pasta)/'comparacao_motores.json').write_text(json.dumps(results,indent=2,ensure_ascii=False))
    return results



## 4. Verificações de comportamento
Executa testes sem YOLO ou GPU. Abrange tolerância limitada, ambiguidade de associação, evidências abaixo do limiar, duas pessoas separadas, recuperação, nova ação e proteção contra duplicação. Testes sintéticos não substituem vídeos reservados.


In [ ]:
# Testes de comportamento do motor, sem YOLO, GPU ou vídeo.
def testar_motor():
    conf = {'pessoa_normal': .30, 'pessoa_desequilibrio': .65, 'pessoa_queda': .50}
    frames = {'pessoa_desequilibrio': 15, 'pessoa_queda': 15}
    def novo(escalada=True):
        return MotorTemporal(conf, frames, set(CLASSES_RISCO), cooldown=3, permitir_escalada=escalada)
    def alimentar(m, seq):
        for i, cls in enumerate(seq, 1):
            ds = [] if cls is None else [dict(track_id=1, classe=cls, confianca=.95,
                                             x1=0, y1=0, x2=100, y2=100)]
            m.step(i, (i-1)/15, ds)
        return m
    D, Q, N = 'pessoa_desequilibrio', 'pessoa_queda', 'pessoa_normal'
    m=alimentar(novo(), [D]*15+[Q]*30)
    assert [e['tipo_evento'] for e in m.events] == ['abertura_episodio','elevacao_gravidade']
    assert [e['episodio'] for e in m.events] == [1,1]
    assert m.events[1]['tempo_video_s']-m.events[0]['tempo_video_s'] < 3
    assert len(alimentar(novo(False), [D]*15+[Q]*30).events)==1
    assert len(alimentar(novo(), [D]*8+[Q]*7).events)==0
    m=alimentar(novo(), [Q]*15+[N]*15+[Q]*45)
    assert [e['episodio'] for e in m.events]==[1,2]
    assert any(t['transicao']=='encerramento_recuperacao' for t in m.transitions)
    assert len(alimentar(novo(), [Q]*15+[None]*15+[Q]*45).events)==1
    assert len(alimentar(novo(), [Q]*15+[N]*14+[Q]*45).events)==1
    assert len(alimentar(novo(), [Q]*90).events)==1
    assert len(alimentar(novo(), [Q]*15+[D]*60).events)==1
    m=novo()
    for i in range(1,31):
        m.step(i,(i-1)/15,[dict(track_id=None,classe=Q,confianca=.99)])
    assert not m.events
    m=novo()
    for i in range(1,31):
        m.step(i,(i-1)/15,[dict(track_id=1,classe=Q,confianca=.49)])
    assert not m.events
    print('10 cenários do motor verificados: elevação, legado, contadores, rearme, ausência, recuperação incompleta, repetição, gravidade, sem ID e baixa confiança.')

testar_motor()

# Testes autocontidos: executáveis no notebook, sem detector/GPU.
def testar_v3():
    conf = {'pessoa_normal': .30, 'pessoa_desequilibrio': .65, 'pessoa_queda': .50}
    frames = {'pessoa_desequilibrio': 15, 'pessoa_queda': 15}
    Q, N, D = 'pessoa_queda', 'pessoa_normal', 'pessoa_desequilibrio'
    A=(0,0,100,200); B=(300,0,400,200)
    feitos=[]
    def make(dedup=True):
        return MotorTemporal(conf,frames,{Q,D},cooldown=3,fps=15,deduplicar_quedas=dedup)
    def det(tid,cls=Q,box=A,score=.95):
        return dict(track_id=tid,classe=cls,confianca=score,
                    **dict(zip(('x1','y1','x2','y2'),box)))
    def feed(m, blocks):
        i=0
        for count, ds in blocks:
            for _ in range(count):
                i+=1; m.step(i,(i-1)/15,ds)
        return m
    def assoc(m):return [t for t in m.transitions if t['transicao']=='associacao_duplicata_queda']
    m=feed(make(),[(30,[det(1)]),(45,[det(2)])])
    assert len(m.events)==1 and len(assoc(m))==1
    feitos.append('troca de ID e persistência não duplicam a mesma queda')
    m=feed(make(False),[(30,[det(1)]),(45,[det(2)])])
    assert len(m.events)==2
    feitos.append('modo V2 sem proteção reproduz duplicação')
    m=feed(make(),[(30,[det(1)]),(30,[det(2)]),(15,[det(2,N)]),(45,[det(2)])])
    assert len(m.events)==2 and m.events[-1]['track_id']==2 and m.events[-1]['episodio']==2
    feitos.append('ID associado recupera, rearma e emite nova queda')
    m=feed(make(),[(30,[det(1)]),(30,[]),(45,[det(2)])])
    assert len(m.events)==2 and not assoc(m)
    feitos.append('intervalo maior que limite não associa posição antiga')
    m=feed(make(),[(30,[det(1)]),(60,[det(2,box=B)])])
    assert len(m.events)==2 and not assoc(m)
    feitos.append('pessoas espacialmente separadas não são associadas')
    m=feed(make(),[(15,[det(1,D)]),(45,[det(1)])])
    assert len(m.events)==2 and m.events[1]['tipo_evento']=='elevacao_gravidade'
    feitos.append('elevação de desequilíbrio para queda preservada')
    m=feed(make(),[(15,[det(1)]),(15,[det(1,N)]),(45,[det(1)])])
    assert len(m.events)==2
    feitos.append('rearme normal do mesmo ID preservado')
    m=feed(make(),[(15,[det(1)]),(15,[]),(45,[det(1)])])
    assert len(m.events)==1
    feitos.append('ausência não é recuperação')
    m=feed(make(),[(30,[det(1)]),(45,[det(None)])])
    assert len(m.events)==1 and not assoc(m)
    feitos.append('detecção sem ID não abre evento nem associação')
    m=feed(make(),[(30,[det(1)]),(45,[det(2,score=.49)])])
    assert len(m.events)==1 and not assoc(m)
    feitos.append('confiança abaixo do limite não confirma queda')
    m=feed(make(),[(8,[det(1,D)]),(7,[det(1)])])
    assert not m.events
    feitos.append('contadores de classes não se somam')
    m=make()
    # Duas referências de episódios diferentes na mesma posição: associação ambígua.
    for tid in [1,2]:
        st=m.new_state();st.update(active=True,severity=Q,fall_box=A,fall_s=1.,event_ref=f'cam:{tid}:1')
        m.states[tid]=st
    cand,amb=m.duplicate_fall(3,A,1.1,m.states)
    assert cand is None and amb
    feitos.append('ambiguidade entre ocorrências não suprime por associação')
    m=feed(make(),[(30,[det(1)]),(15,[det(1,N),det(2)]),(45,[det(2)])])
    assert len(m.events)==2 and not assoc(m)
    feitos.append('normalidade atual da referência impede associação à caixa antiga')
    # As caixas entram em ordem inversa; a decisão deve ser a mesma.
    seq=[(30,[det(1)]),(45,[det(1),det(2)])]
    ma=feed(make(),seq); mb=feed(make(),[(c,list(reversed(ds))) for c,ds in seq])
    assert [(e['frame'],e['track_id']) for e in ma.events]==[(e['frame'],e['track_id']) for e in mb.events]
    assert len(assoc(ma))==len(assoc(mb))==1
    feitos.append('ordem das caixas não altera a associação neste cenário')
    print(f'{len(feitos)} cenários V3 verificados:')
    for item in feitos:print('•',item)
    return feitos

testar_v3()


"""Testes de comportamento e regressão, sem detector/GPU."""
import json
from pathlib import Path

def testar_continuidade():
    conf = {'pessoa_normal': .30, 'pessoa_desequilibrio': .65, 'pessoa_queda': .50}
    frames = {'pessoa_desequilibrio': 15, 'pessoa_queda': 10}
    Q, N, D = 'pessoa_queda', 'pessoa_normal', 'pessoa_desequilibrio'
    A, B = (0,0,100,200), (400,0,500,200)
    feitos = []
    def novo(**opts):
        return MotorTemporalContinuo(conf, frames, {Q,D}, fps=15, cooldown=0,
            deduplicar_quedas=True, **opts)
    def d(tid=1, cls=Q, box=A, score=.95):
        return dict(track_id=tid,classe=cls,confianca=score,
            **dict(zip(('x1','y1','x2','y2'),box)))
    def feed(m, blocks):
        i=0
        for n, ds in blocks:
            for _ in range(n):
                i+=1; m.step(i,(i-1)/15,ds)
        return m
    def check(ok, label):
        assert ok, label
        feitos.append(label)
    check(not feed(novo(),[(9,[d()])]).events, 'nove evidências não confirmam dez')
    m=feed(novo(),[(5,[d()]),(1,[d(cls=N)]),(5,[d()])])
    check(len(m.events)==1 and m.events[0]['frame']==11, 'um frame normal interrompido é tolerado sem contar como queda')
    check(not feed(novo(),[(5,[d()]),(2,[d(cls=N)]),(5,[d()])]).events,
          'duas interrupções excedem a janela padrão')
    check(len(feed(novo(),[(5,[d()]),(1,[]),(5,[d()])]).events)==1,
          'um frame ausente é tolerado, sem fabricar detecção')
    check(not feed(novo(),[(9,[d()]),(1,[])]).events,
          'não confirma no frame ausente')
    check(len(feed(novo(),[(5,[d()]),(1,[d(score=.49)]),(5,[d()])]).events)==1,
          'baixa confiança pode ser interrupção, nunca evidência positiva')
    m=feed(novo(),[(5,[d(1)]),(5,[d(2)])])
    check(len(m.events)==1 and m.events[0]['track_id']==2 and len(m.auditoria_continuidade)==1,
          'troca única de ID transfere evidência pendente')
    check(not feed(novo(),[(5,[d(1)]),(5,[d(2,box=B)])]).events,
          'distância espacial impede transferência')
    check(not feed(novo(),[(5,[d(1)]),(10,[]),(5,[d(2)])]).events,
          'intervalo longo impede transferência')
    m=feed(novo(),[(5,[d(1),d(2)]),(5,[d(3)])])
    check(not m.events and not m.auditoria_continuidade,
          'duas origens compatíveis impedem handoff ambíguo')
    m=feed(novo(),[(5,[d(1)]),(5,[d(2),d(3,cls=N)])])
    check(not m.events and not m.auditoria_continuidade,
          'duas pessoas atuais, inclusive normal, impedem disputar a mesma origem')
    m=feed(novo(),[(10,[d(1)]),(25,[d(2)])])
    check(len(m.events)==1 and any(t['transicao']=='associacao_duplicata_queda' for t in m.transitions)
          and not m.auditoria_continuidade, 'episódio confirmado usa proteção V3 e não transfere contagem ativa')
    m=feed(novo(),[(15,[d(cls=D)]),(10,[d()])])
    check([e['tipo_evento'] for e in m.events]==['abertura_episodio','elevacao_gravidade'],
          'elevação de desequilíbrio para queda preservada')
    m=feed(novo(),[(10,[d()]),(15,[d(cls=N)]),(10,[d()])])
    check([e['episodio'] for e in m.events]==[1,2], 'quinze normais encerram e permitem nova queda')
    check(len(feed(novo(),[(10,[d()]),(14,[d(cls=N)]),(10,[d()])]).events)==1,
          'quatorze normais não rearmam')
    check(len(feed(novo(),[(10,[d()]),(15,[]),(10,[d()])]).events)==1,
          'ausência não rearma episódio ativo')
    check(not feed(novo(),[(8,[d(cls=D)]),(7,[d()])]).events,
          'desequilíbrio não é somado à queda')
    check(not feed(novo(),[(30,[d(tid=None)])]).events, 'sem ID não abre episódio')
    check(not feed(novo(),[(30,[d(score=.49)])]).events, 'rejeitadas não confirmam episódio')
    check(not feed(novo(),[(5,[d(),d()])]).events, 'mesmo ID não acumula duas vezes por frame')
    m=feed(novo(),[(10,[d(1),d(2,box=B)])])
    check(len(m.events)==2 and all(e.get('evidencias_queda')==10 for e in m.events),
          'duas pessoas separadas mantêm evidências e metadados independentes')
    m=novo();m.step(1,0,[d()])
    try:
        m.step(1,0,[d()])
        raise AssertionError('frame repetido aceito')
    except AssertionError as ex:
        assert 'Frames precisam' in str(ex)
    feitos.append('reprocessamento do mesmo frame é rejeitado')
    # Limite zero mantém confirmação estrita em uma sequência interrompida.
    check(not feed(novo(tolerancia_queda=0,handoff=False),[(5,[d()]),(1,[]),(5,[d()])]).events,
          'tolerância zero restaura confirmação consecutiva')
    print(f'{len(feitos)} cenários V4 verificados.')
    return feitos


CENARIOS_V4 = testar_continuidade()


10 cenários do motor verificados: elevação, legado, contadores, rearme, ausência, recuperação incompleta, repetição, gravidade, sem ID e baixa confiança.
14 cenários V3 verificados:
• troca de ID e persistência não duplicam a mesma queda
• modo V2 sem proteção reproduz duplicação
• ID associado recupera, rearma e emite nova queda
• intervalo maior que limite não associa posição antiga
• pessoas espacialmente separadas não são associadas
• elevação de desequilíbrio para queda preservada
• rearme normal do mesmo ID preservado
• ausência não é recuperação
• detecção sem ID não abre evento nem associação
• confiança abaixo do limite não confirma queda
• contadores de classes não se somam
• ambiguidade entre ocorrências não suprime por associação
• normalidade atual da referência impede associação à caixa antiga
• ordem das caixas não altera a associação neste cenário
23 cenários V4 verificados.


## 5. Executar a comparação
No replay, os dois motores recebem as mesmas saídas gravadas. Não gera outro vídeo anotado: consulte os tempos no vídeo do pacote original. No modo vídeo, V3 executa a inferência e V4 reaplica as caixas registradas; a anotação V4 é opcional.


In [ ]:
VIDEOS = {}
if MODO_TESTE == 'replay_zip':
    EXECUCOES = comparar_zip_v3(ZIP_ENTRADA, PASTA, continuidade=CONTINUIDADE)
else:
    VIDEOS['track_v3'] = run(MODELO,VIDEO,PASTA/'track_v3',mode='track',
        confidencias=CONFIANCA_POR_CLASSE, frames_por_classe=FRAMES_POR_CLASSE,
        classes_evento=CLASSES_QUE_GERAM_EVENTO,iou=IOU,imgsz=IMGSZ,
        normal_frames=FRAMES_NORMAL_PARA_ENCERRAR,cooldown=COOLDOWN_S,
        camera_id=CAMERA_ID,mostrar_descartadas=MOSTRAR_DESCARTADAS,
        permitir_escalada=True,deduplicar_quedas=True,
        dedup_iou=DEDUP_IOU,dedup_intervalo_s=DEDUP_INTERVALO_S)
    cfg=json.loads((PASTA/'track_v3'/'configuracao.json').read_text())
    csv_text=(PASTA/'track_v3'/'deteccoes.csv').read_text(encoding='utf-8-sig')
    frames=carregar_registros(cfg,csv_text)
    origem=dict(pasta_origem='track_v3',sha256_csv_entrada=hashlib.sha256(csv_text.encode()).hexdigest(),
                detector_executado_uma_vez=True)
    _, rows_v4=executar_motor(cfg,frames,PASTA/'replay_v4',v4=True,
                             origem=origem,continuidade=CONTINUIDADE)
    EXECUCOES=['track_v3','replay_v4']
    if ANOTAR_VIDEO_V4:
        VIDEOS['replay_v4']=anotar_v4(VIDEO,rows_v4,PASTA/'replay_v4',MOSTRAR_DESCARTADAS)


{
  "status": "concluido",
  "frames": 519,
  "duracao_nominal_s": 51.99132222222222,
  "eventos_locais": 3,
  "aberturas": 3,
  "elevacoes": 0,
  "encerramentos": 1,
  "associacoes_duplicata": 0,
  "eventos_por_classe": {
    "pessoa_desequilibrio": 0,
    "pessoa_queda": 3
  },
  "deteccoes_recebidas": {
    "pessoa_desequilibrio": 133,
    "pessoa_normal": 281,
    "pessoa_queda": 159
  },
  "deteccoes_aceitas": {
    "pessoa_desequilibrio": 72,
    "pessoa_normal": 281,
    "pessoa_queda": 151
  },
  "deteccoes_descartadas": {
    "pessoa_desequilibrio": 61,
    "pessoa_normal": 0,
    "pessoa_queda": 8
  },
  "deteccoes_sem_id": 5,
  "frames_sem_caixas_retornadas": 5,
  "frames_sem_deteccao_aceita": 36,
  "frames_com_supressao_cooldown": 0,
  "processamento_s": 106.64596911499939,
  "inferencia_media_ms": 201.592017499033,
  "fps_processamento": 4.866569306903175,
  "observacao": "Sem referência humana: não calcula precisão, revocação ou falsos alertas. Eventos são locais."
}


## 6. Comparar eventos e recuperação
Mais eventos não significam automaticamente melhora. Verifique ações simuladas, falsos alertas, duplicações e encerramentos. No `Queda01Chuva`, procure a primeira queda perto de 6,625 s; no `QuedaDia02`, preserve o encerramento perto de 36,518 s; no `Queda02Chuva`, preserve as quatro quedas e a nova ação após recuperação.

`replay_v4` no modo vídeo significa que V4 reaplicou as mesmas caixas da inferência V3; não significa que o vídeo deixou de ser processado pelo detector. Tempos são do vídeo, não latência até o aplicativo.


In [ ]:
COMPARACAO = mostrar_comparacao(PASTA,EXECUCOES)
if MODO_TESTE == 'video':
    from IPython.display import Video,display
    for nome,path in VIDEOS.items():
        print(nome)
        display(Video(path,embed=True,width=800))



 track_v3 {
  "status": "concluido",
  "frames": 519,
  "duracao_nominal_s": 51.99132222222222,
  "eventos_locais": 3,
  "aberturas": 3,
  "elevacoes": 0,
  "encerramentos": 1,
  "associacoes_duplicata": 0,
  "eventos_por_classe": {
    "pessoa_desequilibrio": 0,
    "pessoa_queda": 3
  },
  "deteccoes_recebidas": {
    "pessoa_desequilibrio": 133,
    "pessoa_normal": 281,
    "pessoa_queda": 159
  },
  "deteccoes_aceitas": {
    "pessoa_desequilibrio": 72,
    "pessoa_normal": 281,
    "pessoa_queda": 151
  },
  "deteccoes_descartadas": {
    "pessoa_desequilibrio": 61,
    "pessoa_normal": 0,
    "pessoa_queda": 8
  },
  "deteccoes_sem_id": 5,
  "frames_sem_caixas_retornadas": 5,
  "frames_sem_deteccao_aceita": 36,
  "frames_com_supressao_cooldown": 0,
  "processamento_s": 106.64596911499939,
  "inferencia_media_ms": 201.592017499033,
  "fps_processamento": 4.866569306903175,
  "observacao": "Sem referência humana: não calcula precisão, revocação ou falsos alertas. Eventos são loca

replay_v4


## Evidências locais e limites
Nos oito ZIPs recentes (3.163 frames), a referência reproduziu os eventos originais. A variante com uma interrupção e handoff recuperou a primeira simulação do `Queda01Chuva` no frame 67, aos 6,624790 s. A segunda queda desse vídeo antecipou três frames e a terceira permaneceu. As quedas do `QuedaDia02` e `Queda02Chuva` foram preservadas, assim como todos os encerramentos por recuperação registrados pela referência. No `QuedaDia01`, a segunda ação antecipou um frame; a primeira continua bloqueada pelo episódio inicial indevido.

Os quatro vídeos normais mantiveram os mesmos cinco alertas indevidos. Não houve correção desses falsos alertas. A melhoria foi observada nos próprios vídeos usados para desenvolver a regra; não demonstra generalização, superioridade geral ao V6, reidentificação ou desempenho em tempo real. Não houve novo treinamento nem verificação local completa com detector; o modo vídeo deve ser executado com os pesos e originais no Colab.

Recomenda-se validar primeiro o replay do `Queda01Chuva`, depois os demais ZIPs V3, e então executar o original em `video`. Use vídeos novos e casos com duas pessoas para avaliar generalização. Não altere confianças e tolerância ao mesmo tempo.


## 7. Baixar os resultados
Envie o ZIP gerado para avaliação. Ele contém detecções, eventos, transições, transferências pendentes, configurações e comparação dos motores. Em modo vídeo, inclui as anotações geradas. Não publica em RabbitMQ, Firebase ou aplicativo.


In [ ]:
import shutil
ZIP = shutil.make_archive(str(PASTA),'zip',str(PASTA))
files.download(ZIP)


<IPython.core.display.Javascript object>

<IPython.core.display.Javascript object>